# Install atomic simulation environment and simulation code

This sets up our simulation environment. ASE (Atomic Simulation Environment) builds molecules, and GPAW (a DFT code) simulates molecules and computes energies using electronic structure calculations and by approximating the electron cloud.

In [1]:
# install ASE (atomic simulation environment) using Linux
!apt install ase

# install GPAW (the simulation code) using Linux
!apt install python3-mpi4py cython3 libxc-dev gpaw-data
!pip -q install gpaw

Reading package lists... Done
Building dependency tree... Done
Reading state information... Done
The following additional packages will be installed:
  blt fonts-dejavu-core fonts-dejavu-mono fonts-font-awesome
  fonts-glyphicons-halflings fonts-lyx isympy-common isympy3 libimagequant0
  libjs-bootstrap liblbfgsb0 libraqm0 libsymspg2 python-matplotlib-data
  python3-appdirs python3-ase python3-attr python3-brotli python3-bs4
  python3-chardet python3-contourpy python3-cssselect python3-cycler
  python3-dateutil python3-decorator python3-fonttools python3-fs
  python3-html5lib python3-kiwisolver python3-lxml python3-lz4
  python3-matplotlib python3-mpmath python3-olefile python3-pil
  python3-pil.imagetk python3-scipy python3-soupsieve python3-spglib
  python3-sympy python3-tk python3-tz python3-ufolib2 python3-unicodedata2
  python3-webencodings tk8.6-blt2.5 unicode-data
Suggested packages:
  python-ase-doc blt-demo python3-netcdf4 python3-pycodcif python-attr-doc
  python-cycler-doc p

In [6]:
# import tools from ASE
from ase import Atoms, Atom
from ase.build import molecule as ase_molecule
from ase.data.pubchem import pubchem_atoms_search
from ase.visualize import view

# import tools from GPAW
from gpaw import GPAW, PW

# import tools for plotting
import matplotlib.pyplot as plt
import plotly.graph_objects as go

# import tools for numerical calculations
import numpy as np

# 1. Create the molecule

Change the CID to simulate different molecules—e.g., 297 for methane. This pulls atomic positions from PubChem.

In [7]:
"""
define molecule using the PubChem database of the National Library of Medecine

methane         = 297
propane         = 6334
ethanol         = 702
octane          = 10907
oxygen          = 977
carbon dioxide  = 280
water           = 962
hydrogen        = n/a   (type the command "molecule = ase_molecule('H2')"
                        instead of "molecule = pubchem_atoms_search(cid=XXX)")

"""
molecule = molecule = pubchem_atoms_search(cid=280)
molecule.set_cell([7, 7, 7], scale_atoms=False)
molecule.center()

# 2. Visualize the molecule

In [8]:
# show molecule
view(molecule, viewer='x3d', block=True)

# 3. Calculate the energy of the molecule

Run the simulation. This solves the Kohn-Sham equations to get the total energy for each molecule.

In [9]:
# set simulation parameters
calc = GPAW(xc='PBE',
            kpts=(1,1,1),
            mode=PW(700),
            basis='dzp')
molecule.set_calculator(calc)

# run computer simulation (using quantum mechanics to compute the electron cloud)
energy = molecule.get_total_energy()

print("*****")
print(" The energy of the molecule is "+str(energy)+" eV")
print("*****")

  __  _  _
 | _ |_)|_||  |
 |__||  | ||/\| - 26.7.0

User:   ???@8f0c6ba93b60
Date:   Fri Sep 11 10:23:48 2026
Arch:   x86_64
Pid:    2072
CWD:    /content
units:  Angstrom and eV
cores:  1
OpenMP: False

Versions:
  Python: 3.13.15
  ASE:    3.29.0
  Numpy:  2.1.3
  Scipy:  1.16.3
  Libxc:  5.2.3

Paths:
  gpaw:  /usr/local/lib/python3.13/dist-packages/gpaw
  _gpaw: /usr/local/lib/python3.13/dist-packages/
        _gpaw.cpython-313-x86_64-linux-gnu.so
  ase:   /usr/local/lib/python3.13/dist-packages/ase
  numpy: /usr/local/lib/python3.13/dist-packages/numpy
  scipy: /usr/local/lib/python3.13/dist-packages/scipy

Git-hashes:

OMP_NUM_THREADS: 


Environment variables:
  GPAW_CPUPY:          False
  GPAW_DEBUG:          False
  GPAW_MPI_BACKEND:    serial
  GPAW_MPI_OPTIONS:    None
  GPAW_NO_C_EXTENSION: False
  GPAW_NO_GPU_MPI:     False
  GPAW_TRACE:          False
  GPAW_USE_GPUS:       False

Input parameters:
  mode=PW(ecut=700.0),
  basis={'default': 'dzp'},
  kpts=MonkhorstPack(

/tmp/ipykernel_2072/3826156675.py:6: FutureWarning: Please use atoms.calc = calc
  molecule.set_calculator(calc)



Diagonalizing LCAO Hamiltonian
Converting LCAO to pw mode
     .----------------.  
    /|                |  
   / |                |  
  /  |                |  
 *   |                |  
 |   |                |  
 |   |   O  C O       |  
 |   |                |  
 |   |                |  
 |   .----------------.  
 |  /                /   
 | /                /    
 |/                /     
 *----------------*      

Atoms  # Å, Bohr magnetons
|   | symbol |        x |        y |        z |    initial magnetic moments |
|---|--------|----------|----------|----------|-----------------------------|
| 0 |      O | 2.303000 | 3.500000 | 3.500000 | ( 0.0000,  0.0000,  0.0000) |
| 1 |      O | 4.697000 | 3.500000 | 3.500000 | ( 0.0000,  0.0000,  0.0000) |
| 2 |      C | 3.500000 | 3.500000 | 3.500000 | ( 0.0000,  0.0000,  0.0000) |


Unit cell  # Å
| periodic |        x |        y |        z |  lengths |    angles |
|----------|----------|----------|----------|----------|-----------|
|   

# 4. Visualize the electron cloud of the molecule

The electron cloud represents the probability distribution of an electron's position around an atom or molecule, derived from simulations. It shows where the electron is most likely to be found, with denser areas indicating higher probability. This is the 'cloud' that determines bonding.

In [10]:
# convert electron cloud
n = calc.get_all_electron_density(gridrefinement=4)
nred = n[::3,::3,::3]
X, Y, Z = np.mgrid[0:7:60j, 0:7:60j, 0:7:60j]

# show electron cloud
fig = go.Figure(data=go.Isosurface(
    x=X.flatten(),
    y=Y.flatten(),
    z=Z.flatten(),
    value=nred.flatten(),
    isomin=0.1,
    isomax=1,
    surface_count=5,
    colorbar_nticks=5,
    caps=dict(x_show=False, y_show=False),
    opacity=0.3
    ))

fig.show()